$$
\frac{\partial u}{\partial t}
+u\frac{\partial u}{\partial x}
+v\frac{\partial u}{\partial y}
=\nu\left(\frac{\partial^2u}{\partial x^2}
+\frac{\partial^2u}{\partial y^2}\right)

\newline



\frac{\partial v}{\partial t}
+u\frac{\partial v}{\partial x}
+v\frac{\partial v}{\partial y}
=\nu\left(\frac{\partial^2v}{\partial x^2}
+\frac{\partial^2v}{\partial y^2}\right)
$$

In [46]:
import numpy as np
import scipy as sp
import matplotlib.pyplot as plt

In [47]:
# Domain
Lx = 2 * np.pi
Ly = 2 * np.pi

# Number of grid points
Nx = 101
Ny = 101

dx = Lx / Nx
dy = Ly / Ny

# Periodic grid: do not duplicate the endpoint
x = np.linspace(0, Lx, Nx, endpoint=False)
y = np.linspace(0, Ly, Ny, endpoint=False)

X, Y = np.meshgrid(x, y)

nu = 0.05
t_final = 1.0
cfl = 0.4

In [48]:
def upwind_derivative(q, velocity, axis, spacing): ##first order upwind
    

    backward = (q - np.roll(q, 1, axis=axis)) / spacing

    forward = (np.roll(q, -1, axis=axis) - q) / spacing

    return np.where(velocity >= 0, backward, forward)


def laplacian(q, dx, dy): ##central differencing
  

    d2q_dx2 = (np.roll(q, -1, axis=1)
        - 2 * q
        + np.roll(q, 1, axis=1)) / dx**2

    d2q_dy2 = (np.roll(q, -1, axis=0)
        - 2 * q
        + np.roll(q, 1, axis=0)) / dy**2

    return d2q_dx2 + d2q_dy2

In [49]:
# Initial condition
u = 5*np.sin(X) * np.cos(Y)
v = -5*np.cos(X) * np.sin(Y)

u_initial = u.copy()
v_initial = v.copy()

In [50]:
def burgers_step(u, v, dt, nu, dx, dy):
    # Derivatives of u
    du_dx = upwind_derivative(u, u, axis=1, spacing=dx)
    du_dy = upwind_derivative(u, v, axis=0, spacing=dy)

    # Derivatives of v
    dv_dx = upwind_derivative(v, u, axis=1, spacing=dx)
    dv_dy = upwind_derivative(v, v, axis=0, spacing=dy)

    # Diffusion
    lap_u = laplacian(u, dx, dy)
    lap_v = laplacian(v, dx, dy)

    # Right-hand sides of the PDEs
    rhs_u = -(u * du_dx + v * du_dy) + nu * lap_u
    rhs_v = -(u * dv_dx + v * dv_dy) + nu * lap_v

    # Explicit Euler update
    u_new = u + dt * rhs_u
    v_new = v + dt * rhs_v

    return u_new, v_new

In [51]:
t = 0.0
steps = 0

while t < t_final:

    # Conservative advection time-step limit
    max_adv_rate = (
        np.max(np.abs(u)) / dx
        + np.max(np.abs(v)) / dy
    )

    if max_adv_rate > 0:
        dt_adv = cfl / max_adv_rate
    else:
        dt_adv = np.inf

    # Diffusion time-step limit for 2D explicit Euler
    if nu > 0:
        dt_diff = 0.45 / (
            nu * (1 / dx**2 + 1 / dy**2)
        )
    else:
        dt_diff = np.inf

    # Do not advance past the final time
    dt = min(dt_adv, dt_diff, t_final - t)

    u, v = burgers_step(u, v, dt, nu, dx, dy)

    t += dt
    steps += 1

print(f"Simulation time: {t:.4f}")
print(f"Time steps: {steps}")
print(f"Maximum velocity magnitude: "
      f"{np.max(np.sqrt(u**2 + v**2)):.4f}")

Simulation time: 1.0000
Time steps: 282
Maximum velocity magnitude: 1.7980


In [52]:
import numpy as np


def solve_burgers(u0, v0, nu, dx, dy, t_final,
                  n_frames=100, cfl=0.4):

    # Times at which we want to save the solution
    times = np.linspace(0.0, t_final, n_frames + 1)

    # Store the initial condition
    u = u0.copy()
    v = v0.copy()

    U_history = [u.copy()]
    V_history = [v.copy()]

    t = 0.0
    total_steps = 0

    # Advance the solution between successive output times
    for target_t in times[1:]:

        while t < target_t - 1e-12:

            # Advection time-step limit
            max_adv_rate = (
                np.max(np.abs(u)) / dx
                + np.max(np.abs(v)) / dy
            )

            dt_adv = (
                cfl / max_adv_rate
                if max_adv_rate > 0
                else np.inf
            )

            # Diffusion time-step limit
            dt_diff = (
                0.45 / (nu * (1/dx**2 + 1/dy**2))
                if nu > 0
                else np.inf
            )

            # Stop exactly at the next output time
            dt = min(dt_adv, dt_diff, target_t - t)

            u, v = burgers_step(
                u, v, dt, nu, dx, dy
            )

            t += dt
            total_steps += 1

        # Record the solution at this output time
        t = target_t
        U_history.append(u.copy())
        V_history.append(v.copy())

    # Convert lists into arrays
    U_history = np.stack(U_history)
    V_history = np.stack(V_history)

    print(f"Solution complete.")
    print(f"Total solver steps: {total_steps}")
    print(f"Saved output frames: {len(times)}")

    return times, U_history, V_history

In [53]:
times, U_history, V_history = solve_burgers(
    u0=u_initial,
    v0=v_initial,
    nu=nu,
    dx=dx,
    dy=dy,
    t_final=t_final,
    n_frames=100,
    cfl=0.4
)

Solution complete.
Total solver steps: 321
Saved output frames: 101


In [54]:
import matplotlib.pyplot as plt
from matplotlib.animation import FuncAnimation
from IPython.display import HTML, display

# Initial saved velocity field
speed = np.sqrt(U_history[0]**2 + V_history[0]**2)

# Use one fixed color scale for the entire animation
vmax = max(
    1.2 * np.max(np.sqrt(U_history**2 + V_history**2)),
    1e-12
)

fig, ax = plt.subplots(figsize=(8, 7))

im = ax.imshow(
    speed,
    origin="lower",
    extent=[0, Lx, 0, Ly],
    cmap="viridis",
    vmin=0,
    vmax=vmax,
    aspect="equal",
    interpolation="bilinear"
)

# Velocity arrows
skip = 5

arrows = ax.quiver(
    X[::skip, ::skip],
    Y[::skip, ::skip],
    U_history[0, ::skip, ::skip],
    V_history[0, ::skip, ::skip],
    color="white"
)

title = ax.set_title(f"2D Burgers' Equation | t = {times[0]:.3f}")

ax.set_xlabel("x")
ax.set_ylabel("y")

fig.colorbar(im, ax=ax, label="Velocity magnitude")
plt.tight_layout()


def update(frame):

    # Retrieve stored results; do not solve anything
    u = U_history[frame]
    v = V_history[frame]

    speed = np.sqrt(u**2 + v**2)

    im.set_data(speed)

    arrows.set_UVC(
        u[::skip, ::skip],
        v[::skip, ::skip]
    )

    title.set_text(
        f"2D Burgers' Equation | t = {times[frame]:.3f}"
    )

    return im, arrows, title


anim = FuncAnimation(
    fig,
    update,
    frames=len(times),
    interval=40,
    blit=False,
    repeat=False
)

plt.close(fig)

display(HTML(anim.to_jshtml()))

Animation size has reached 21174555 bytes, exceeding the limit of 20971520.0. If you're sure you want a larger animation embedded, set the animation.embed_limit rc parameter to a larger value (in MB). This and further frames will be dropped.


In [55]:
def burgers_rhs(u, v, nu, dx, dy):
    # First derivatives of u
    du_dx = upwind_derivative(u, u, axis=1, spacing=dx)
    du_dy = upwind_derivative(u, v, axis=0, spacing=dy)

    # First derivatives of v
    dv_dx = upwind_derivative(v, u, axis=1, spacing=dx)
    dv_dy = upwind_derivative(v, v, axis=0, spacing=dy)

    # Diffusion terms
    lap_u = laplacian(u, dx, dy)
    lap_v = laplacian(v, dx, dy)

    # Right-hand sides
    rhs_u = -(u * du_dx + v * du_dy) + nu * lap_u
    rhs_v = -(u * dv_dx + v * dv_dy) + nu * lap_v

    return rhs_u, rhs_v


def burgers_step(u, v, dt, nu, dx, dy):

    # Stage 1: evaluate at the current state
    k1_u, k1_v = burgers_rhs(u, v, nu, dx, dy)

    # Stage 2: evaluate at a half-step using stage 1
    k2_u, k2_v = burgers_rhs(
        u + 0.5 * dt * k1_u,
        v + 0.5 * dt * k1_v,
        nu, dx, dy
    )

    # Stage 3: evaluate at a half-step using stage 2
    k3_u, k3_v = burgers_rhs(
        u + 0.5 * dt * k2_u,
        v + 0.5 * dt * k2_v,
        nu, dx, dy
    )

    # Stage 4: evaluate at a full step using stage 3
    k4_u, k4_v = burgers_rhs(
        u + dt * k3_u,
        v + dt * k3_v,
        nu, dx, dy
    )

    # Combine all four stages
    u_new = u + (dt / 6.0) * (
        k1_u + 2*k2_u + 2*k3_u + k4_u
    )

    v_new = v + (dt / 6.0) * (
        k1_v + 2*k2_v + 2*k3_v + k4_v
    )

    return u_new, v_new

In [56]:
u = 5*np.sin(X) * np.cos(Y)
v = -5*np.cos(X) * np.sin(Y)

u_initial = u.copy()
v_initial = v.copy()

def solve_burgers(u0, v0, nu, dx, dy, t_final,
                  n_frames=100, cfl=0.4):

    # Times at which we want to save the solution
    times = np.linspace(0.0, t_final, n_frames + 1)

    # Store the initial condition
    u = u0.copy()
    v = v0.copy()

    U_history = [u.copy()]
    V_history = [v.copy()]

    t = 0.0
    total_steps = 0

    # Advance the solution between successive output times
    for target_t in times[1:]:

        while t < target_t - 1e-12:

            # Advection time-step limit
            max_adv_rate = (
                np.max(np.abs(u)) / dx
                + np.max(np.abs(v)) / dy
            )

            dt_adv = (
                cfl / max_adv_rate
                if max_adv_rate > 0
                else np.inf
            )

            # Diffusion time-step limit
            dt_diff = (
                0.45 / (nu * (1/dx**2 + 1/dy**2))
                if nu > 0
                else np.inf
            )

            # Stop exactly at the next output time
            dt = min(dt_adv, dt_diff, target_t - t)

            # Advance using the RK4 solver
            u, v = burgers_step(
                u, v, dt, nu, dx, dy
            )

            t += dt
            total_steps += 1

        # Record the solution at this output time
        t = target_t
        U_history.append(u.copy())
        V_history.append(v.copy())

    # Convert lists into arrays
    U_history = np.stack(U_history)
    V_history = np.stack(V_history)

    print(f"Solution complete.")
    print(f"Total solver steps: {total_steps}")
    print(f"Saved output frames: {len(times)}")

    return times, U_history, V_history

In [57]:
import matplotlib.pyplot as plt
from matplotlib.animation import FuncAnimation
from IPython.display import HTML, display

# Initial saved velocity field
speed = np.sqrt(U_history[0]**2 + V_history[0]**2)

# Use one fixed color scale for the entire animation
vmax = max(
    1.2 * np.max(np.sqrt(U_history**2 + V_history**2)),
    1e-12
)

fig, ax = plt.subplots(figsize=(8, 7))

im = ax.imshow(
    speed,
    origin="lower",
    extent=[0, Lx, 0, Ly],
    cmap="viridis",
    vmin=0,
    vmax=vmax,
    aspect="equal",
    interpolation="bilinear"
)

# Velocity arrows
skip = 5

arrows = ax.quiver(
    X[::skip, ::skip],
    Y[::skip, ::skip],
    U_history[0, ::skip, ::skip],
    V_history[0, ::skip, ::skip],
    color="white"
)

title = ax.set_title(f"2D Burgers' Equation | t = {times[0]:.3f}")

ax.set_xlabel("x")
ax.set_ylabel("y")

fig.colorbar(im, ax=ax, label="Velocity magnitude")
plt.tight_layout()


def update(frame):

    # Retrieve stored results; do not solve anything
    u = U_history[frame]
    v = V_history[frame]

    speed = np.sqrt(u**2 + v**2)

    im.set_data(speed)

    arrows.set_UVC(
        u[::skip, ::skip],
        v[::skip, ::skip]
    )

    title.set_text(
        f"2D Burgers' Equation | t = {times[frame]:.3f}"
    )

    return im, arrows, title


anim = FuncAnimation(
    fig,
    update,
    frames=len(times),
    interval=40,
    blit=False,
    repeat=False
)

plt.close(fig)

display(HTML(anim.to_jshtml()))

Animation size has reached 21174555 bytes, exceeding the limit of 20971520.0. If you're sure you want a larger animation embedded, set the animation.embed_limit rc parameter to a larger value (in MB). This and further frames will be dropped.
